In [2]:
from tldhamburg.backend.DataFetcher import DataFetcher
import json

In [8]:
data_fetcher = DataFetcher()

endpoint = "Datastreams"
params = {
    "$filter": "properties/layerName eq 'primary_signal'",
    "$expand" : "Thing($expand=Locations)",
}

data_fetcher.fetch_data(endpoint,params)

print(f"Retrieved {len(data_fetcher.get_data())} datastreams.")

Retrieved 20018 datastreams.


In [11]:
print(json.dumps(data_fetcher.get_data()[0],indent=4))

{
    "@iot.selfLink": "https://tld.iot.hamburg.de/v1.1/Datastreams(31878)",
    "@iot.id": 31878,
    "name": "Primary signal heads at 2287_17",
    "description": "Datastream to broadcast the lane connection's signal value of a signal group",
    "observationType": "http://www.opengis.net/def/ogc-om/OM_CategoryObservation",
    "unitOfMeasurement": {
        "name": "Signal Status ",
        "symbol": "[0-6,9]",
        "definition": "0=dark,1=red,2=amber,3=green,4=red-amber,5=amber-flashing,6=green-flashing,9=unknown"
    },
    "observedArea": {
        "type": "Polygon",
        "coordinates": [
            [
                [
                    10.1495832,
                    53.4915984
                ],
                [
                    10.2083553,
                    53.4921557
                ],
                [
                    10.2083554,
                    53.4921557
                ],
                [
                    10.1495832,
                    53.49159

In [12]:
data_fetcher = DataFetcher()

endpoint = "Datastreams"
params = {
    "$filter": "properties/layerName eq 'primary_signal'",
    "$select" : "id,observedArea"
}

data_fetcher.fetch_data(endpoint,params)

print(f"Retrieved {len(data_fetcher.get_data())} datastreams.")

Retrieved 20018 datastreams.


In [13]:
print(json.dumps(data_fetcher.get_data()[0],indent=4))

{
    "@iot.id": 48775,
    "observedArea": {
        "type": "Point",
        "coordinates": [
            10.0873341,
            53.5776903
        ]
    }
}


In [14]:
results = dict()

for stream in data_fetcher.get_data():
    if "observedArea" not in stream.keys():
        if "noObservedArea" not in results:
            results["noObservedArea"] = 0
        results["noObservedArea"] +=1
    else: 
        type = stream["observedArea"]["type"]
        if type not in results:
            results[type] = 0
        results[type] += 1
print(results)
print(sum([value for _,value in results.items()]))


{'Point': 9447, 'LineString': 9462, 'Polygon': 966, 'noObservedArea': 143}
20018


In [15]:
import folium
from IPython.display import display

def switch_coords(coords):
    temp = coords[0]
    coords[0] = coords[1]
    coords[1] = temp

#save possible colors for markers
colors = ['red', 'blue', 'green', 'purple', 'orange', 'darkred', 'lightred', 'beige', 'darkblue', 'darkgreen', 'cadetblue', 'darkpurple', 'white', 'pink', 'lightblue', 'lightgreen', 'gray', 'black']
def create_marker(coords,color_index):
    folium.CircleMarker(location=coords,radius=1,color = colors[color_index], fill = True, fill_color = colors[color_index], opacity = 1).add_to(map_object)
#define starting point for map (chosen arbitrarily)
hamburg_mid_point = [53.571974, 9.969119]

#create maps
map_object = folium.Map(location=hamburg_mid_point, zoom_start=12)


counter = 0
for stream in data_fetcher.get_data():
    if "observedArea" not in stream.keys():
        continue
    
    if stream["observedArea"]["type"] == "Point":
        coords = stream["observedArea"]["coordinates"]
        switch_coords(coords)
        create_marker(coords,0)
    elif stream["observedArea"]["type"] == "LineString":
        coord_pairs = stream["observedArea"]["coordinates"]
        for coords in coord_pairs:
            switch_coords(coords)  # latidute and longitude are given switch up by the API
            #add Marker for each coordinate_pair
            create_marker(coords,1)
    else:
        coord_pairs = stream["observedArea"]["coordinates"][0]
        for coords in coord_pairs:
            switch_coords(coords)  # latidute and longitude are given switch up by the API
            create_marker(coords,2)

# Display the map
display(map_object)